In [ ]:
# %%
import os
import pandas as pd
import json
import subprocess
from datetime import datetime
import re
import folium

# Paths

In [8]:
JSON_PATH = r"\\192.168.20.101\webdata\Nav\old"

In [ ]:
"""Write a program to get all .json files in JSON_PATH and drop duplicates using serverTime and get results to a panda dataframe"""
# %%


In [11]:
# Get all .json files in JSON_PATH and drop duplicates using serverTime
json_files = [
    os.path.join(JSON_PATH, file)
    for file in os.listdir(JSON_PATH)
    if file.endswith(".json")
]

# Combine all JSON files into a single dataframe
dataframes = []
for file in json_files:
    with open(file, "r") as f:
        data = json.load(f)
        dataframes.append(pd.DataFrame(data))

# Concatenate all dataframes
combined_df = pd.concat(dataframes, ignore_index=True)

# Drop duplicates based on 'serverTime' column
if "serverTime" in combined_df.columns:
    combined_df = combined_df.drop_duplicates(subset="serverTime")

print(combined_df)

          latitude   longitude                                    address  \
0          6.15878   80.093462                 535V+F9W, ගාල්ල, Sri Lanka   
1         6.159015   80.093238                      Address not available   
2         6.159015   80.093238                      Address not available   
3         6.159015   80.093238                      Address not available   
4         6.159015   80.093238                      Address not available   
...            ...         ...                                        ...   
2939854    6.19013   80.096357                                        NaN   
3020576    6.15889   80.092905                      Address not available   
3091873  6.1453753  80.0956032                                              
3229924   6.158693   80.093608                 535V+F9W, ගාල්ල, Sri Lanka   
3288394   6.158867   80.093358  11-67 Seenigama - Aluthwala Rd, Sri Lanka   

        old_latitude old_longitude               lat,long localTime  \
0   

In [13]:
os.path.join("./output", "combined_data.parquet")

'./output\\combined_data.parquet'

In [15]:
combined_df.dtypes

latitude         object
longitude        object
address          object
old_latitude     object
old_longitude    object
lat,long         object
localTime        object
batteryLevel     object
googleAccount    object
lastUpdate       object
serverTime       object
dtype: object

In [22]:
# Ensure latitude and longitude columns are numeric
combined_df["latitude"] = pd.to_numeric(combined_df["latitude"], errors="coerce")
combined_df["longitude"] = pd.to_numeric(combined_df["longitude"], errors="coerce")

# Ensure all columns have consistent data types
combined_df["address"] = combined_df["address"].astype(str)
combined_df["old_latitude"] = combined_df["old_latitude"].astype(str)
combined_df["old_longitude"] = combined_df["old_longitude"].astype(str)

# Drop rows with invalid latitude or longitude
combined_df = combined_df.fillna(0)

# Ensure the 'lat,long' column is properly formatted as a string
combined_df["lat,long"] = combined_df["lat,long"].astype(str)

# Save the dataframe to a Parquet file
combined_df.to_parquet(os.path.join("./output", "combined_data.parquet"), index=False)

In [24]:
combined_df.head(2)

,latitude,longitude,address,old_latitude,old_longitude,"lat,long",localTime,batteryLevel,googleAccount,lastUpdate,serverTime
0,6.158780,80.093462,"535V+F9W, ගාල්ල, Sri Lanka",6.1635893,80.0754356,"6.15878, 80.0934617",5:27 am,100%,Navoda Madubashini,15 min ago,"06/03/2025, 10:57:20"
1,6.159015,80.093238,Address not available,6.1554969,80.0915271,"6.1590155, 80.0932379",3:16 pm,51%,Navoda Madubashini,6 min ago,"23/03/2025, 20:46:34"


In [26]:
combined_df.sort_values(by="serverTime", ascending=False, inplace=True)
combined_df.to_parquet(os.path.join("./output", "combined_data.parquet"), index=False)

In [37]:
DIAMETER_KMS = 1

In [36]:
CENTER_LAT, CENTER_LON = 6.15878, 80.0934617

In [ ]:
''' DIAMETER_KMS is giben in kilometers. filter combined_df dataframe so that locations 
identified by  latitude and longitude columns are outside the circle with center
(CENTER_LAT, CENTER_LON) and radius DIAMETER_KMS. '''

In [41]:
import numpy as np


# Function to calculate the Haversine distance
def haversine(lat1, lon1, lat2, lon2):
    R = 6371  # Earth radius in kilometers
    lat1, lon1, lat2, lon2 = map(np.radians, [lat1, lon1, lat2, lon2])
    dlat = lat2 - lat1
    dlon = lon2 - lon1
    a = np.sin(dlat / 2) ** 2 + np.cos(lat1) * np.cos(lat2) * np.sin(dlon / 2) ** 2
    c = 2 * np.arcsin(np.sqrt(a))
    return R * c


# Calculate distances from the center
combined_df["distance_from_center"] = haversine(
    combined_df["latitude"], combined_df["longitude"], CENTER_LAT, CENTER_LON
)

# Filter rows where the distance is greater than the radius
filtered_df = combined_df[combined_df["distance_from_center"] > DIAMETER_KMS / 2]
filtered_df = filtered_df[filtered_df["latitude"] > 0]
filtered_df = filtered_df[filtered_df["longitude"] > 0]
print(filtered_df)

       latitude  longitude                                       address  \
33738  6.159713  80.098003                         Address not available   
33752  6.159692  80.098585                         Address not available   
33757  6.159940  80.099330                    536X+2PQ, Galle, Sri Lanka   
3127   6.155975  80.097420                         Address not available   
26534  6.157990  80.088623                         Address not available   
...         ...        ...                                           ...   
47409  6.140294  80.100043                          Hikkaduwa, Sri Lanka   
47410  6.140294  80.100043                          Hikkaduwa, Sri Lanka   
47411  6.140976  80.099642  179 Galle - Colombo Rd, Hikkaduwa, Sri Lanka   
47412  6.144758  80.099190         Colombo Main Rd, Hikkaduwa, Sri Lanka   
47413  6.150517  80.097700                147 Colombo Main Rd, Sri Lanka   

      old_latitude old_longitude               lat,long localTime  \
33738    6.1567431

In [42]:
filtered_df.head(2)

,latitude,longitude,address,old_latitude,old_longitude,"lat,long",localTime,batteryLevel,googleAccount,lastUpdate,serverTime,distance_from_center
33738,6.159713,80.098003,Address not available,6.1567431,80.0842978,"6.1597133, 80.0980032",2:41 pm,22%,Navoda Madubashini,A moment ago,"31/03/2025, 20:11:47",0.512690
33752,6.159692,80.098585,Address not available,6.1567431,80.0842978,"6.1596917, 80.0985849",2:13 pm,22%,Navoda Madubashini,A moment ago,"31/03/2025, 19:43:47",0.575387


In [43]:
"""show filtered_df on a map using folium. The icons should be numbered from 1 to n, where n is the number of rows in filtered_df.
When clicked on an icon it should show all the information in the row in a popup.
It should also have clickable link to open the location on Google Maps."""

'show filtered_df on a map using folium. The icons should be numbered from 1 to n, where n is the number of rows in filtered_df.\nWhen clicked on an icon it should show all the information in the row in a popup.\nIt should also have clickable link to open the location on Google Maps.'

In [ ]:
map_ = folium.Map(
    location=[filtered_df["latitude"].mean(), filtered_df["longitude"].mean()],
    zoom_start=15,
)

In [50]:
for i, row in filtered_df.iterrows():
    popup_content = f"""
    <b>Index:</b> {i}<br>
    <b>Latitude:</b> {row['latitude']}<br>
    <b>Longitude:</b> {row['longitude']}<br>
    <b>Address:</b> {row['address']}<br>
    <b>Local Time:</b> {row['localTime']}<br>
    <b>Battery Level:</b> {row['batteryLevel']}<br>
    <b>Google Account:</b> {row['googleAccount']}<br>
    <b>Last Update:</b> {row['lastUpdate']}<br>
    <b>Server Time:</b> {row['serverTime']}<br>
    <b>Distance from Center:</b> {row['distance_from_center']} km<br>
    <a href="https://www.google.com/maps?q={row['latitude']},{row['longitude']}" target="_blank">Open in Google Maps</a>
    """
    folium.Marker(
        location=[row["latitude"], row["longitude"]],
        popup=folium.Popup(popup_content, max_width=300),
        icon=folium.Icon(color="blue", icon="info-sign"),
        tooltip=f"Point {i + 1}",
    ).add_to(map_)

In [52]:
map_.save(os.path.join("./output", "location_list.html"))

In [ ]:


# Create a map centered at the average latitude and longitude of the filtered_df




# Display the map
map_